In [7]:
##------------Imports, paths------------

import os
import zipfile
import sqlite3
import requests
import pandas as pd
import numpy as np
import plotly.express as px
import plotly.graph_objects as go
from plotly.subplots import make_subplots

nrows=500000
source_url = "https://www.fs.usda.gov/rds/archive/products/RDS-2013-0009.7/RDS-2013-0009.7_Data_Format4_SQLITE.zip"    
local_dir = "wildfire_7th_edition_data"
os.makedirs(local_dir, exist_ok=True)
zip_path = os.path.join(local_dir, "us_wildfires_v7.zip")

In [8]:
##------------Data download - run one time only------------

if 1==1:
    print("📡 Initializing browser emulation handshake with U.S. Forest Service...")
    # 1. BYPASS 403 FORBIDDEN: Fake a verified user desktop connection header
    headers = {
        'User-Agent': 'Mozilla/5.0 (Windows NT 10.0; Win64; x64) AppleWebKit/537.36 (KHTML, like Gecko) Chrome/120.0.0.0 Safari/537.36'
    }
    # 2. STREAM SECURE TRANSFER: Download block-by-block to keep memory low
    if not os.path.exists(zip_path):
        print("📥 Streaming 7th Edition database (~219MB compressed package)... Please wait.")
        with requests.get(source_url, headers=headers, stream=True) as response:
            response.raise_for_status()
            with open(zip_path, 'wb') as f:
                for chunk in response.iter_content(chunk_size=16384):
                    if chunk:
                        f.write(chunk)
        print("✅ Download finished completely.")
        
    # 3. EXTRACTION SEQUENCE
    print("🔓 Unpacking compressed archive contents...")
    with zipfile.ZipFile(zip_path, 'r') as zip_ref:
        zip_ref.extractall(local_dir)

if 1==1: 
    # 4. READ metadata file    
    data_dir = local_dir+'/Data/'
    df_meta = pd.read_csv(data_dir+'_variable_descriptions.csv', keep_default_na=False)
    print(df_meta)

    # 5. READ data file
    db_path = data_dir+'FPA_FOD_20260615.sqlite'
    conn = sqlite3.connect(db_path)
    cursor = conn.cursor()

    # 6. List all available tables within the master catalog schema
    cursor.execute("SELECT name FROM sqlite_master WHERE type='table';")
    print("📁 Available Tables in Database:")
    tables = cursor.fetchall()
    for t in tables:
        print(f"   ↳ {t[0]}")

    # 7. Inspect column headers and data types inside the main 'Fires' table
    cursor.execute("PRAGMA table_info(Fires);")
    print("\n📊 Column Schema Details for 'Fires' Table:")
    columns = cursor.fetchall()
    for col in columns:
        # col[1] = Column Name, col[2] = Data Type (TEXT, REAL, INT)
        print(f"   ↳ Header: {col[1]:<20} | Type: {col[2]}")


📡 Initializing browser emulation handshake with U.S. Forest Service...
🔓 Unpacking compressed archive contents...
                                              Filename            Variable  \
0                       \Data\FPA_FOD_20260615 [Fires]              FOD_ID   
1                       \Data\FPA_FOD_20260615 [Fires]              FPA_ID   
2                       \Data\FPA_FOD_20260615 [Fires]  SOURCE_SYSTEM_TYPE   
3                       \Data\FPA_FOD_20260615 [Fires]  SOURCE_SYSTEM_TYPE   
4                       \Data\FPA_FOD_20260615 [Fires]  SOURCE_SYSTEM_TYPE   
..                                                 ...                 ...   
202  \Data\FPA_FOD_20260615 [NWCG_UnitIdActive_2020...             Country   
203  \Data\FPA_FOD_20260615 [NWCG_UnitIdActive_2020...             Country   
204  \Data\FPA_FOD_20260615 [NWCG_UnitIdActive_2020...               State   
205  \Data\FPA_FOD_20260615 [NWCG_UnitIdActive_2020...                Code   
206  \Data\FPA_FOD_20260615 

In [9]:
##------------Load data------------

if 1==1:
    # The 7th Edition utilizes updated National Wildfire Coordinating Group (NWCG) columns
    query = f"""
    SELECT 
        OBJECTID,
        FIRE_NAME,
        COMPLEX_NAME,
        FIRE_YEAR,
        DISCOVERY_DATE,
        DISCOVERY_DOY,
        DISCOVERY_TIME,
        CONT_DATE,
        CONT_DOY,
        CONT_TIME,
        FIRE_SIZE,
        FIRE_SIZE_CLASS,
        LATITUDE,
        LONGITUDE,
        OWNER_DESCR,
        STATE,
        COUNTY,
        FIPS_NAME,
        FIPS_CODE,
        NWCG_REPORTING_AGENCY,
        SOURCE_SYSTEM_TYPE,
        NWCG_CAUSE_CLASSIFICATION,
        NWCG_GENERAL_CAUSE
    FROM Fires
    WHERE CONT_DATE IS NOT NULL 
      AND DISCOVERY_DATE IS NOT NULL
    LIMIT {nrows};
    """
    df = pd.read_sql_query(query, conn)
    conn.close()
    
    print(f"🎉 Success! 7th Edition Data Matrix populated smoothly. Shape: {df.shape}")
    print("\n--- Sample Telemetry Output ---")
df

🎉 Success! 7th Edition Data Matrix populated smoothly. Shape: (500000, 23)

--- Sample Telemetry Output ---


,OBJECTID,FIRE_NAME,COMPLEX_NAME,FIRE_YEAR,DISCOVERY_DATE,DISCOVERY_DOY,DISCOVERY_TIME,CONT_DATE,CONT_DOY,CONT_TIME,...,LONGITUDE,OWNER_DESCR,STATE,COUNTY,FIPS_NAME,FIPS_CODE,NWCG_REPORTING_AGENCY,SOURCE_SYSTEM_TYPE,NWCG_CAUSE_CLASSIFICATION,NWCG_GENERAL_CAUSE
0,1,FOUNTAIN,NaN,2005,2453403.5,33,1300,2453403.5,33,1730,...,-121.005833,USFS,CA,63,Plumas County,06063,FS,FED,Human,Power generation/transmission/distribution
1,2,PIGEON,NaN,2004,2453137.5,133,0845,2453137.5,133,1530,...,-120.404444,USFS,CA,61,Placer County,06061,FS,FED,Natural,Natural
2,3,SLACK,NaN,2004,2453156.5,152,1921,2453156.5,152,2024,...,-120.735556,STATE OR PRIVATE,CA,17,El Dorado County,06017,FS,FED,Human,Debris and open burning
3,4,DEER,NaN,2004,2453184.5,180,1600,2453189.5,185,1400,...,-119.913333,USFS,CA,3,Alpine County,06003,FS,FED,Natural,Natural
4,5,STEVENOT,NaN,2004,2453184.5,180,1600,2453189.5,185,1200,...,-119.933056,USFS,CA,3,Alpine County,06003,FS,FED,Natural,Natural
...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...,...
499995,741793,NaN,NaN,1993,2449166.5,179,NaN,2449167.5,180,1010,...,-81.158333,MISSING/NOT SPECIFIED,SC,32,Lexington County,45063,ST/C&L,NONFED,Missing data/not specified/undetermined,Missing data/not specified/undetermined
499996,741794,NaN,NaN,1993,2449168.5,181,NaN,2449168.5,181,NaN,...,-81.425000,MISSING/NOT SPECIFIED,SC,32,Lexington County,45063,ST/C&L,NONFED,Missing data/not specified/undetermined,Missing data/not specified/undetermined
499997,741795,NaN,NaN,1993,2449168.5,181,NaN,2449168.5,181,NaN,...,-81.325000,MISSING/NOT SPECIFIED,SC,32,Lexington County,45063,ST/C&L,NONFED,Missing data/not specified/undetermined,Missing data/not specified/undetermined
499998,741796,NaN,NaN,1992,2448815.5,194,NaN,2448815.5,194,1215,...,-80.962500,MISSING/NOT SPECIFIED,SC,38,Orangeburg County,45075,ST/C&L,NONFED,Missing data/not specified/undetermined,Missing data/not specified/undetermined


## Data Integrity & Artifact Profiling

In [10]:
##------------Missing DISCOVERY_TIME by source system------------
disc_time_missing = df['DISCOVERY_TIME'].fillna('').astype(str).str.strip() == ''

missing_by_source = (disc_time_missing.groupby(df['SOURCE_SYSTEM_TYPE'])
                       .agg(['mean', 'size']).reset_index())
missing_by_source['Missing (%)'] = missing_by_source['mean'] * 100
missing_by_source = missing_by_source.rename(columns={'size': 'Fires'})
print(missing_by_source[['SOURCE_SYSTEM_TYPE', 'Fires', 'Missing (%)']].round(1).to_string(index=False))

fig = px.bar(missing_by_source, x='SOURCE_SYSTEM_TYPE', y='Missing (%)',
             text=missing_by_source['Missing (%)'].round(1),
             labels={'SOURCE_SYSTEM_TYPE': 'Source system'},
             title='Missing DISCOVERY_TIME by Source System')
fig.show()

SOURCE_SYSTEM_TYPE  Fires  Missing (%)
               FED 368035          0.1
         INTERAGCY    287        100.0
            NONFED 131678         29.7


**Observations:** `DISCOVERY_TIME` is missing for 0.1% of FED fires, 29.7% of NONFED fires, and 100% of the 287 INTERAGCY fires. The missingness depends on who reported the fire, not on the fire itself, so any hour-of-day analysis mainly reflects federal fires.

In [11]:
##------------Repeated and rounded coordinates------------
coord_counts = (df.groupby(['LATITUDE', 'LONGITUDE'])
                  .size().reset_index(name='n_fires')
                  .sort_values('n_fires', ascending=False))

shared = coord_counts.loc[coord_counts['n_fires'] > 1, 'n_fires'].sum()
print(f"Unique locations: {len(coord_counts):,} for {len(df):,} fires")
print(f"Fires sharing a location with another fire: {shared/len(df)*100:.1f}%")
print(coord_counts.head(10).to_string(index=False))

lat_decimals = df['LATITUDE'].astype(str).str.split('.').str[1].str.len()
fig = px.histogram(x=lat_decimals,
                   labels={'x': 'Decimal places in LATITUDE'},
                   title='Coordinate Precision: Decimal Places in LATITUDE')
fig.update_layout(yaxis_title='Number of fires', bargap=0.1)
fig.show()

Unique locations: 450,746 for 500,000 fires
Fires sharing a location with another fire: 14.6%
 LATITUDE  LONGITUDE  n_fires
  41.0665  -123.6845      355
  32.5848  -116.8347      336
  33.3353  -110.4518      281
  36.0001   -95.0002      225
  47.8666   -95.0169      183
  42.1167   -96.3670      168
  33.3517  -110.4518      163
  41.0832  -123.6845      162
  33.3501  -110.4507      139
  41.0499  -123.6678      133


**Observations:** 14.6% of fires share an exact location with another fire, and one point holds 355 fires. Most coordinates have 4 or 8 decimal places, but about 55,000 fires have only 1–3, so their locations are approximate. These stacked points can look like false hotspots in spatial analysis.

## Administrative Scale: Fire Size by Cause

In [12]:
##------------Fire size (log scale) by general cause------------
d = df[df['FIRE_SIZE'] > 0]
order = d.groupby('NWCG_GENERAL_CAUSE')['FIRE_SIZE'].median().sort_values().index

fig = px.box(d, x='FIRE_SIZE', y='NWCG_GENERAL_CAUSE', log_x=True, points=False,
             category_orders={'NWCG_GENERAL_CAUSE': list(order)},
             labels={'FIRE_SIZE': 'Fire size (acres, log scale)', 'NWCG_GENERAL_CAUSE': 'General cause'},
             title='Fire Size by General Cause')
fig.update_layout(height=550)
fig.show()

**Observations:** Most fires are small for every cause: all median sizes are about 2 acres or less. Arson and firearms/explosives have the largest medians (about 2 acres), while natural, recreation and "other" fires have the smallest (about 0.1 acre). However, natural fires have the longest upper range, reaching roughly 600,000 acres, so lightning fires are usually tiny but also produce the largest fires. Many boxes start at exactly 0.1 acre, which suggests 0.1 acre is a common minimum recorded size rather than a true measurement.